In [41]:
from encodec import EncodecModel
from encodec.utils import convert_audio

import torchaudio
import torch
import IPython.display as ipd


El modelo EnCodec trabaja con una **tasa de compresión temporal** que reduce la resolución temporal del audio.

**Ej: audio 10s@24kHz**
1. **Tasa de muestreo del audio original**
   - El audio original tiene una duración de 10 segundos y una frecuencia de muestreo de 24 kHz.
   - El audio tiene `10 * 24,000 = 240,000` muestras en total.

2. **Compresión temporal en EnCodec**
   - El modelo EnCodec no trabaja directamente con todas las muestras del audio. En su lugar, utiliza un **stride temporal** o **factor de reducción** para comprimir la representación temporal del audio.
   - Para `sr=24kHz`, el encoder produce 75 "pasos latentes" por segundo (para `sr=48kHz`, produce 150 pasos latentes por segundo).
   - Es decir, el factor de reducción es **320**.
   - Total de pasos de tiempo en los códigos: 
   $$
    \frac{\text{Número total de muestras}}{\text{Stride temporal}} = \frac{240,000}{320} = 750
   $$

3. **Relación entre los códigos y el audio**
   - Los 750 pasos de tiempo en los códigos representan los 10 segundos del audio original, pero en una forma comprimida.
   - Cada paso de tiempo en los códigos abarca un segmento de audio de:
     $$
     \text{Duración por paso} = \frac{\text{Duración total del audio}}{\text{Pasos de tiempo}} = \frac{10}{750} \approx 0.0133 \, \text{segundos (13.3 ms)}.
     $$

4. **Ventajas de la compresión temporal**
   - Esta compresión reduce significativamente la cantidad de datos necesarios para representar el audio, lo que es útil para tareas como transmisión o almacenamiento.
   - Sin embargo, la calidad del audio reconstruido depende de la cantidad de codebooks (`n_q`) y el ancho de banda seleccionado.

# Encodear un audio

Probamos todos los bitrates para escuchar la calidad tanto a 24 como 48 Khz.

In [4]:
path_ = '/Volumes/stuff/ELECE/Cientifico/Educativo/Tesis-grado/v2/proyecto/data/EARS/convolved_dataset/files/train/clean/p001/00000.wav'
wav, sr = torchaudio.load(path_)
print(f'original sr: {sr}')

original sr: 48000


## $S_{rate}=24Khz$

Supported bandwidths are 1.5kbps (n_q = 2), 3 kbps (n_q = 4), 6 kbps (n_q = 8) and 12 kbps (n_q =16) and 24kbps (n_q=32).

In [31]:
model24 = EncodecModel.encodec_model_24khz()
print(f'{model24.bits_per_codebook=}')
print(f'{model24.channels=}')
print(f'{model24.frame_rate=}')
print(f'{model24.overlap=}')
print(f'{model24.sample_rate=}')
print(f'{model24.target_bandwidths=}')

model24.bits_per_codebook=10
model24.channels=1
model24.frame_rate=75
model24.overlap=0.01
model24.sample_rate=24000
model24.target_bandwidths=[1.5, 3.0, 6, 12.0, 24.0]


In [58]:
from IPython.display import display

print('Audio original')
audio = ipd.Audio(filename=path_)
display(audio)

for bw in reversed(model24.target_bandwidths):
    print(f'Audio encoded @ {bw=}')
    model24.set_target_bandwidth(bw)
    # convert_auidio basicamente downsamplea
    wav_ds = convert_audio(wav, sr, model24.sample_rate, model24.channels)
    wav_ds = wav_ds.unsqueeze(0)
    with torch.no_grad():
        encoded_frames = model24.encode(wav_ds)
        decoded_wav = model24.decode(encoded_frames)
        display(ipd.Audio(decoded_wav[0], rate=model24.sample_rate))


Audio original


Audio encoded @ bw=24.0


Audio encoded @ bw=12.0


Audio encoded @ bw=6.0


Audio encoded @ bw=3.0


## $S_{rate}=48kHz$

For the 48 kHz model, only 3, 6, 12, and 24 kbps are supported. Note that the 48 kHz model processes the audio by chunks of 1 seconds, with an overlap of 1%, and renormalizes the audio to have unit scale. For this model, the output of model.encode(wav) would a list (for each frame of 1 second) of a tuple (codes, scale) with scale a scalar tensor.

In [55]:
model48 = EncodecModel.encodec_model_48khz()
print(f'{model48.bits_per_codebook=}')
print(f'{model48.channels=}')
print(f'{model48.frame_rate=}')
print(f'{model48.overlap=}')
print(f'{model48.sample_rate=}')
print(f'{model48.target_bandwidths=}')

model48.bits_per_codebook=10
model48.channels=2
model48.frame_rate=150
model48.overlap=0.01
model48.sample_rate=48000
model48.target_bandwidths=[3.0, 6.0, 12.0, 24.0]


In [56]:
from IPython.display import display

print('Audio original')
audio = ipd.Audio(filename=path_)
display(audio)
ipd.Audio(filename=path_)

for bw in reversed(model48.target_bandwidths):
    print(f'Audio encoded @ {bw=}')
    model24.set_target_bandwidth(bw)
    # convert_auidio basicamente downsamplea
    wav_ds = convert_audio(wav, sr, model48.sample_rate, model48.channels)
    wav_ds = wav_ds.unsqueeze(0)
    with torch.no_grad():
        encoded_frames = model48.encode(wav_ds)
        decoded_wav = model48.decode(encoded_frames)
        display(ipd.Audio(decoded_wav[0], rate=model48.sample_rate))


Audio original


Audio encoded @ bw=24.0


Audio encoded @ bw=12.0


Audio encoded @ bw=6.0


Audio encoded @ bw=3.0


# Decode codebooks to waveform

In [62]:
model24 = EncodecModel.encodec_model_24khz()
model24.set_target_bandwidth(24)
wav_ds = convert_audio(wav, sr, model24.sample_rate, model24.channels)
wav_ds = wav_ds.unsqueeze(0)
with torch.no_grad():
    encoded_frames = model24.encode(wav_ds)
    
codes = torch.cat([encoded[0] for encoded in encoded_frames], dim=-1)  # [B, n_q, T]    
# decoded_wav = model24.decode(encoded_frames)


In [63]:
codes

tensor([[[  62,  408,  738,  ...,  325,  976,  753],
         [ 913,  518,   87,  ...,   87, 1007,  687],
         [ 989,  678,   36,  ...,  618,  458,  856],
         ...,
         [ 639,  511,  672,  ...,  320,  470, 1002],
         [ 621,  665,  672,  ...,  364,  606,  906],
         [ 567,  549,  588,  ...,  938,  948,  861]]])

# Train the encoder